## Transform Results Data
- Read bronze Results table
- Keep only the columns required for analytics(Drop url column)
- Standardise column name using snakecase(constructorId->constructor_id,driverId->driver_id)
- Rename columns to make them more meaningful(grid->grid_position)
- Filter out rows where seaon,round,constructor_id and driver_id is null (business key validation)
- Remove duplicate records.
- Transform values of column race_name to Title Case
- Write the transformed data to silver results table

In [0]:
%run ../00-common/01.environment-config

In [0]:
bronze_table=f"{catalog_name}.{bronze_schema}.results"
silver_table=f"{catalog_name}.{silver_schema}.results"

In [0]:
import pyspark.sql.functions as F

### Step 1,2,3&4 Read bronze results table,select only required colum and standardise column names

In [0]:
results_df=(
    spark.table(bronze_table)
    .drop("url")
    .withColumnsRenamed(
        {"constructorId":"constructor_id",
         "driverId":"driver_id",
         "raceName":"race_name",
         "date":"race_date",
         "time":"race_time",
         "grid":"grid_position",
         "laps":"completed_laps",
         "number":"car_number",
         "position":"final_position",
         "positionText":"final_position_text"
        }
    )
)
    


### Step 5 & 6  Apply Data Quality Checks
- Filter out rows where seaon,round,constructor_id and driver_id is null (business key validation)
- Remove Duplicates

In [0]:
results_valid_df=(
    results_df.filter(
        F.col("season").isNotNull() &
        F.col("round").isNotNull() &
        F.col("driver_id").isNotNull() &
        F.col("constructor_id").isNotNull()
    )
    .dropDuplicates(["season","round","driver_id","constructor_id"])
)



In [0]:

display(results_valid_df)



race_date,race_name,round,season,constructor_id,driver_id,grid_position,completed_laps,car_number,points,final_position,final_position_text,status,ingestion_timestamp,source_file
1970-03-07,south african grand prix,1,1970,mclaren-ford,surtees,7,60,7,0.0,15,R,Engine,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-03-07,south african grand prix,1,1970,brabham,stommelen,15,23,14,0.0,21,R,Engine,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-05-10,monaco grand prix,3,1970,mclaren-ford,hulme,3,80,11,3.0,4,4,Finished,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-07-05,french grand prix,6,1970,brabham,stommelen,14,38,22,0.0,7,7,Finished,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-07-05,french grand prix,6,1970,march,stewart,4,38,1,0.0,9,9,Finished,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-07-18,british grand prix,7,1970,march,siffert,20,19,15,0.0,19,R,Suspension,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-07-18,british grand prix,7,1970,ferrari,ickx,3,6,3,0.0,22,R,Transmission,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-09-06,italian grand prix,10,1970,brm,eaton,20,21,12,0.0,14,R,Overheating,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-09-06,italian grand prix,10,1970,brm,rodriguez,2,12,10,0.0,18,R,Engine,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-09-20,canadian grand prix,11,1970,march,amon,6,90,20,4.0,3,3,Finished,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json


### Step -7 Transform values of column race_name to Title Case

In [0]:
results_final_df=(
    results_valid_df
    .withColumn("race_name",F.initcap(F.col("race_name")))
)
#display(drivers_final_df)

### Step-8 Write the transformed data to silver drivers table

In [0]:
(
   results_final_df
    .write
    .mode("overwrite")
    .format("delta")
    .option('overwriteSchema', 'true')
    .saveAsTable(silver_table)
)

In [0]:
display(spark.read.table(silver_table))

race_date,race_name,round,season,constructor_id,driver_id,grid_position,completed_laps,car_number,points,final_position,final_position_text,status,ingestion_timestamp,source_file
1970-03-07,South African Grand Prix,1,1970,mclaren-ford,surtees,7,60,7,0.0,15,R,Engine,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-03-07,South African Grand Prix,1,1970,brabham,stommelen,15,23,14,0.0,21,R,Engine,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-05-10,Monaco Grand Prix,3,1970,mclaren-ford,hulme,3,80,11,3.0,4,4,Finished,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-07-05,French Grand Prix,6,1970,brabham,stommelen,14,38,22,0.0,7,7,Finished,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-07-05,French Grand Prix,6,1970,march,stewart,4,38,1,0.0,9,9,Finished,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-07-18,British Grand Prix,7,1970,march,siffert,20,19,15,0.0,19,R,Suspension,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-07-18,British Grand Prix,7,1970,ferrari,ickx,3,6,3,0.0,22,R,Transmission,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-09-06,Italian Grand Prix,10,1970,brm,eaton,20,21,12,0.0,14,R,Overheating,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-09-06,Italian Grand Prix,10,1970,brm,rodriguez,2,12,10,0.0,18,R,Engine,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
1970-09-20,Canadian Grand Prix,11,1970,march,amon,6,90,20,4.0,3,3,Finished,2026-10-06T17:48:53.135Z,dbfs:/Volumes/formula1/landing/files/results/results_1970.json
